In [ ]:
# 3D Taylor-Green turbulence (pseudo-spectral DNS) + live energy spectrum E(k) and flux Pi(k)
# Paste into ONE Colab cell and run. Needs only numpy / scipy / matplotlib (all preinstalled).
# Runs in roughly 20-40 s on a free Colab CPU at N=64.

import time
import numpy as np
import scipy.fft as sfft
import matplotlib.pyplot as plt
from matplotlib import animation
from IPython.display import HTML, display

# ----------------------------- parameters -----------------------------
N          = 64        # grid points per side (64 ~ 30 s on CPU; 32 is ~5 s, 96 is ~2 min)
nu         = 1 / 400   # viscosity (Re = 1/nu); 64^3 can't resolve much beyond ~400-600
dt         = 0.02      # time step (CFL ~ 0.2 at N=64)
t_end      = 30.0       # simulate to this time (dissipation peaks around t ~ 5-9)
snap_every = 10        # store a frame every this many steps
# ----------------------------------------------------------------------

L = 2 * np.pi
x = np.arange(N) * L / N
X, Y, Z = np.meshgrid(x, x, x, indexing="ij")

# wavenumbers for rfftn layout (last axis is half-spectrum)
k1 = np.fft.fftfreq(N, 1 / N)
kz1 = np.fft.rfftfreq(N, 1 / N)
KX, KY, KZ = np.meshgrid(k1, k1, kz1, indexing="ij")
Kvec = np.array([KX, KY, KZ])
K2 = KX**2 + KY**2 + KZ**2
K2inv = np.zeros_like(K2)
K2inv[K2 > 0] = 1.0 / K2[K2 > 0]

# 2/3-rule dealiasing mask
kcut = N // 3
dealias = (np.abs(KX) <= kcut) & (np.abs(KY) <= kcut) & (np.abs(KZ) <= kcut)

# spherical shells for spectra; weight 2 for rfft modes whose conjugate partner is omitted
shell = np.rint(np.sqrt(K2)).astype(int)
wt = np.full(K2.shape, 2.0)
wt[..., 0] = 1.0
wt[..., -1] = 1.0  # Nyquist plane
kk = np.arange(kcut + 1)

fft3 = lambda f: sfft.rfftn(f, axes=(-3, -2, -1), workers=-1)
ifft3 = lambda fh: sfft.irfftn(fh, s=(N, N, N), axes=(-3, -2, -1), workers=-1)


def curl_hat(uh):
    return 1j * np.array([
        KY * uh[2] - KZ * uh[1],
        KZ * uh[0] - KX * uh[2],
        KX * uh[1] - KY * uh[0],
    ])


def nonlinear(uh):
    """Projected, dealiased (u x omega) term: the nonlinear part of Navier-Stokes."""
    u = ifft3(uh)
    w = ifft3(curl_hat(uh))
    cross = np.array([
        u[1] * w[2] - u[2] * w[1],
        u[2] * w[0] - u[0] * w[2],
        u[0] * w[1] - u[1] * w[0],
    ])
    nh = fft3(cross) * dealias
    nh -= Kvec * (np.sum(Kvec * nh, axis=0) * K2inv)  # pressure projection (div-free)
    return nh


def rhs(uh):
    return nonlinear(uh) - nu * K2 * uh


def spectra(uh):
    """Return shell-summed E(k) and energy flux Pi(k) (positive = forward cascade)."""
    s = 1.0 / N**6
    e_modes = 0.5 * wt * np.sum(np.abs(uh) ** 2, axis=0) * s
    nh = nonlinear(uh)
    t_modes = wt * np.real(np.sum(np.conj(uh) * nh, axis=0)) * s  # transfer T(k)
    E = np.bincount(shell.ravel(), e_modes.ravel(), minlength=N)[: kcut + 1]
    T = np.bincount(shell.ravel(), t_modes.ravel(), minlength=N)[: kcut + 1]
    Pi = -np.cumsum(T)  # flux through wavenumber k
    return E, Pi


# ----------------------------- initial condition -----------------------------
u0 = np.array([
    np.sin(X) * np.cos(Y) * np.cos(Z),
    -np.cos(X) * np.sin(Y) * np.cos(Z),
    np.zeros_like(X),
])
uh = fft3(u0) * dealias

# ----------------------------- time loop -----------------------------
nsteps = int(round(t_end / dt))
snaps = []
t0 = time.time()
for n in range(nsteps + 1):
    if n % snap_every == 0:
        E, Pi = spectra(uh)
        wmag = np.linalg.norm(ifft3(curl_hat(uh))[..., N // 4], axis=0)  # slice z = pi/2
        snaps.append(dict(t=n * dt, E=E, Pi=Pi, w=wmag))
    # Heun (RK2) step
    k1_ = rhs(uh)
    k2_ = rhs(uh + dt * k1_)
    uh = uh + 0.5 * dt * (k1_ + k2_)
print(f"Simulated {nsteps} steps on {N}^3 grid in {time.time() - t0:.1f} s, "
      f"{len(snaps)} frames stored.")
print(f"Initial KE = {snaps[0]['E'].sum():.4f} (exact: 0.1250), "
      f"final KE = {snaps[-1]['E'].sum():.4f}")

# ----------------------------- animation -----------------------------
vmax = np.percentile(np.concatenate([s["w"].ravel() for s in snaps]), 99.5)
Emax = max(s["E"][1:].max() for s in snaps)
Pmax = max(np.abs(s["Pi"]).max() for s in snaps)

fig, (axw, axE, axP) = plt.subplots(1, 3, figsize=(16, 4.8), layout="constrained")
im = axw.imshow(snaps[0]["w"].T, origin="lower", cmap="inferno", interpolation="bilinear", vmin=0, vmax=vmax,
                extent=[0, L, 0, L])
axw.set_title("|vorticity|, slice z = π/2")
axw.set_xticks([]); axw.set_yticks([])
kref = np.array([3.0, kcut])
Eref = 0.4 * snaps[-1]["E"][3]  # anchor for the k^-5/3 guide line


def draw(i):
    s = snaps[i]
    im.set_data(s["w"].T)
    axw.set_xlabel(f"t = {s['t']:.2f}")

    axE.clear()
    for j in range(max(0, i - 8), i):  # faded history
        axE.loglog(kk[1:], snaps[j]["E"][1:], color="gray", alpha=0.12 + 0.25 * (j - i + 8) / 8, lw=1)
    axE.loglog(kk[1:], s["E"][1:], "C0", lw=2.5)
    ref = Eref * (kref / 3.0) ** (-5 / 3)  # k^-5/3 guide
    axE.loglog(kref, ref, "k--", lw=1)
    axE.text(kref[0] * 1.6, ref[0] * 1.3, r"$k^{-5/3}$")
    axE.set_xlim(1, kcut); axE.set_ylim(1e-8, 2 * Emax)
    axE.set_xlabel("wavenumber k"); axE.set_ylabel("E(k)")
    axE.set_title("Energy spectrum")
    axE.grid(True, which="both", alpha=0.2)

    axP.clear()
    axP.axhline(0, color="k", lw=0.5)
    axP.plot(kk, s["Pi"], "C3", lw=2.5)
    axP.set_xlim(0, kcut); axP.set_ylim(-0.1 * Pmax, 1.15 * Pmax)
    axP.set_xlabel("wavenumber k"); axP.set_ylabel("Π(k)")
    axP.set_title("Energy flux through k (>0: large → small scales)")
    axP.grid(True, alpha=0.2)
    return []


anim = animation.FuncAnimation(fig, draw, frames=len(snaps), interval=120, blit=False)
html = anim.to_jshtml()
plt.close(fig)
display(HTML(html))

Simulated 1500 steps on 64^3 grid in 209.9 s, 151 frames stored.
Initial KE = 0.1250 (exact: 0.1250), final KE = 0.0093
